(zonas-agg-poblacion)=
# Agregación de zonas Core según poblacion

Esta notebook busca agrupar zonas Core adyacentes que pertenecen a una misma sección censal, con el objetivo de obtener zonas con poblaciones más equilibradas, reduciendo la cantidad de zonas por sección censal a la mitad.

El procedimiento consiste en:

1. Identificar qué zonas Core pertenecen a cada sección censal.
2. Identificar qué zonas son adyacentes entre sí.
3. Seleccionar pares de zonas adyacentes que puedan agruparse.
4. Evaluar distintas cantidades de agrupaciones posibles, siempre de a pares.
5. Conservar la solución que produce poblaciones más equilibradas dentro de cada sección censal.
6. Incorporar nuevamente las zonas que no son Core (Periferia) y generar la zonificación final.

In [1]:
import pandas as pd
import geopandas as gpd
import folium
from itertools import combinations
from shapely.ops import unary_union
import numpy as np
from scipy.optimize import milp, LinearConstraint, Bounds
from shapely.ops import snap
local_crs = 'EPSG:32721'

In [2]:
# En caso de que haya algún proceso aleatorio, con esto controlamos que sea siempre igual. 
np.random.seed(42)

Cargamos las secciones censales, los microdatos del censo y la zonificación a15.

In [3]:
secciones_censales = gpd.read_file("../data/geography-levels/sc_23_pg.gpkg")
censo = pd.read_csv("../data/population/personas_ext_07_2026.csv", encoding='latin-1')
zonificacion_a15 = gpd.read_file("../data/geography-levels/a15.gpkg")

C:\Users\joele\AppData\Local\Temp\ipykernel_11184\909857099.py:2: DtypeWarning: Columns (14,151) have mixed types. Specify dtype option on import or set low_memory=False.
  censo = pd.read_csv("../data/population/personas_ext_07_2026.csv", encoding='latin-1')


Filtramos las personas en situación de calle y construimos el código de segmento censal (`CODSEG`) a partir del departamento, sección y segmento.

In [4]:
censo = censo.loc[censo["SIT_CALLE"] != 1].copy()

# Crear CODSEG en los microdatos. Según la documentación: Departamento = 2 caracteres, Sección = 2 caracteres , Segmento = 3 caracteres
censo["CODSEG"] = (censo["DEPARTAMENTO"].astype(str).str.zfill(2) + censo["SECCION"].astype(str).str.zfill(2) + censo["SEGMENTO"].astype(str).str.zfill(3))

Calculamos la población de cada segmento censal utilizando el ponderador `W` de los microdatos. Asignamos a cada zona la suma de la población de los segmentos censales que la componen. Los segmentos no encontrados se consideran 0 cuando la zona tiene otros segmentos con población; si no se encuentra ningún segmento, la población queda como `NaN`.

In [5]:
poblacion_segmento = censo.groupby("CODSEG")["W"].sum()

def calcular_poblacion(codseg):
    segmentos = [x.strip() for x in codseg.split(",") if x.strip()]
    valores = poblacion_segmento.reindex(segmentos)

    if valores.notna().any():
        return valores.fillna(0).sum()

    return np.nan

zonificacion_a15_con_poblacion = zonificacion_a15.copy()
zonificacion_a15_con_poblacion["poblacion"] = zonificacion_a15_con_poblacion["CODSEG"].apply(calcular_poblacion)

In [6]:
zonificacion_a15_con_poblacion[zonificacion_a15_con_poblacion['poblacion'].isna()]  # zonas que no encontraron personas en 'censo' ubicadas en los segmentos censales que contiene

,poligono_id,tipo_zona,depto_codigo,depto_nombre,seccion_codigo,CODSEG,geometry,poblacion
141,141,Core,16,SAN JOSE,1600,1600000,"POLYGON ((546834.195 6166989.216, 546890.145 6...",NaN
225,225,Core,01,MONTEVIDEO,0118,0118101,"POLYGON ((575708.222 6135349.233, 575707.164 6...",NaN
234,234,Core,01,MONTEVIDEO,0118,0118208,"POLYGON ((576538.744 6135250.746, 576537.923 6...",NaN
299,299,Core,01,MONTEVIDEO,0114,0114015,"POLYGON ((572387.579 6140176.3, 572381.723 614...",NaN
498,498,Core,01,MONTEVIDEO,0125,0125001,"POLYGON ((571704.789 6137058.079, 571702.051 6...",NaN


In [7]:
zonificacion_a15_con_poblacion['area'] = zonificacion_a15_con_poblacion.geometry.area/1000000

El siguiente código busca reducir aproximadamente a la mitad la cantidad de zonas Core dentro de cada sección censal. Para esto, identifica polígonos adyacentes y selecciona las parejas de polígonos cuya población combinada ayuda a minimizar la desviación entre las nuevas zonas. Cada polígono puede participar en una sola unión.

In [8]:
# Nos quedamos solamente con las zonas Core que no son demasiado grandes
zonas_core_ = zonificacion_a15_con_poblacion[zonificacion_a15_con_poblacion["tipo_zona"] == "Core"].copy()
zonas_core_["poblacion"] = pd.to_numeric(zonas_core_["poblacion"], errors="coerce").fillna(0)
q1 = zonas_core_['area'].quantile(0.25)
q3 = zonas_core_['area'].quantile(0.75)
ric = q3-q1
zonas_core_grandes = zonas_core_[(zonas_core_['area'] >= q3 + 1.5*ric)]
zonas_core = zonas_core_[(zonas_core_['area'] < q3 + 1.5*ric)]

def encontrar_adyacencias(grupo, tolerancia=200):
    '''Busca qué polígonos son vecinos dentro de una sección censal. 
    Dos polígonos se consideran adyacentes si comparten más de 0.1 unidades de borde'''
    adyacentes = []
    for i in range(len(grupo)):
        for j in range(i + 1, len(grupo)):
            borde = snap(grupo.geometry.iloc[i].boundary, grupo.geometry.iloc[j].boundary, tolerance=1e-4).intersection(grupo.geometry.iloc[j].boundary)
            if borde.length > tolerancia:
                adyacentes.append((i, j))
    return adyacentes

# Agrupa las zonas Core de una sección censal
def agrupar_seccion(grupo):
    grupo = grupo.reset_index(drop=True)
    n = len(grupo)

    # Si hay una sola zona, no hay nada que unir
    if n <= 1:
        return [{
            "geometry": grupo.geometry.iloc[0],
            "poblacion": grupo.poblacion.iloc[0],
            "poligonos_origen": [grupo.poligono_id.iloc[0]]
        }]

    # Encontramos todos los pares de polígonos que se pueden unir
    assert grupo.crs == local_crs
    adyacentes = encontrar_adyacencias(grupo)

    # Buscamos reducir aproximadamente a la mitad el número de zonas. Cada par representa una unión de dos polígonos
    n_pares = n // 2
    n_pares = min(n_pares, len(adyacentes))
    # if seccion == '0103':
    #         import pdb; pdb.set_trace()
    
    # Si no hay polígonos adyacentes, dejamos las zonas como están
    if n_pares == 0:
        return [{
            "geometry": row.geometry,
            "poblacion": row.poblacion,
            "poligonos_origen": [row.poligono_id]
        } for _, row in grupo.iterrows()]

    # Calculamos el costo de unir cada par de polígonos. El costo es menor cuando las poblaciones son menores
    costos = []
    for i, j in adyacentes:
        pi = grupo.poblacion.iloc[i]
        pj = grupo.poblacion.iloc[j]
        costos.append(2 * pi * pj)

    costos = np.array(costos, dtype=float)

    # Matriz que indica qué polígonos participa en cada posible unión
    A = np.zeros((n, len(adyacentes)))
    for k, (i, j) in enumerate(adyacentes):
        A[i, k] = 1
        A[j, k] = 1

    # Cada polígono puede participar como máximo en una unión
    restricciones = LinearConstraint(A, lb=0, ub=1)

    # Obligamos al modelo a hacer exactamente n_pares uniones
    # Obligamos al modelo a hacer al menos n_pares uniones
    flag = 0
    lb = n_pares
    # if seccion == '0103':
    #         import pdb; pdb.set_trace()
    while flag == 0:
        restriccion_pares = LinearConstraint(np.ones((1, len(adyacentes))),lb=lb,ub=n_pares)

        # Busca la combinación de uniones con menor costo total
        resultado = milp(c=costos, integrality=np.ones(len(adyacentes)), bounds=Bounds(0, 1), constraints=[restricciones, restriccion_pares])

        if resultado.success:
            flag = 1
        else:
            print("No se encontró una solución con lb =", lb, "para la sección", seccion)
            lb -= 1
            if lb ==1:
                flag = 1

    # Si el optimizador no encuentra una solución, dejamos las zonas originales
    if not resultado.success:
        return [{
            "geometry": row.geometry,
            "poblacion": row.poblacion,
            "poligonos_origen": [row.poligono_id]
        } for _, row in grupo.iterrows()]

    # Nos quedamos con los pares seleccionados por el optimizador
    pares_elegidos = [adyacentes[k] for k, valor in enumerate(resultado.x) if valor > 0.5]

    usados = set()
    nuevas_zonas = []

    # Unimos los pares seleccionados
    for i, j in pares_elegidos:
        geom = unary_union([grupo.geometry.iloc[i], grupo.geometry.iloc[j]])
        poblacion = (grupo.poblacion.iloc[i] + grupo.poblacion.iloc[j])

        nuevas_zonas.append({
            "geometry": geom, 
            "poblacion": poblacion, 
            "poligonos_origen": [grupo.poligono_id.iloc[i], grupo.poligono_id.iloc[j]]})
        usados.add(i)
        usados.add(j)

    # # Si queda algún polígono sin pareja, lo dejamos solo
    # for i in range(n):
    #     if i not in usados:
    #         nuevas_zonas.append({
    #             "geometry": grupo.geometry.iloc[i],
    #             "poblacion": grupo.poblacion.iloc[i],
    #             "poligonos_origen": [grupo.poligono_id.iloc[i]]})
    
    # Índice de vecinos usando poligono_id (que es lo que guardamos en cada grupo)
    poligono_ids = grupo.poligono_id.tolist()

    vecinos = {pid: set() for pid in poligono_ids}
    for i, j in adyacentes:
        vecinos[poligono_ids[i]].add(poligono_ids[j])
        vecinos[poligono_ids[j]].add(poligono_ids[i])

    # Cada polígono sobrante se anexa a un grupo vecino (máx. 3 miembros)
    for i in range(n):
        if i in usados:
            continue


        pid = poligono_ids[i]
        
        candidatos = [
            z for z in nuevas_zonas
            if len(z["poligonos_origen"]) < 3
            and vecinos[pid].intersection(z["poligonos_origen"])
        ]

        if candidatos:
            destino = min(candidatos, key=lambda z: z["poblacion"])
            destino["geometry"] = unary_union([destino["geometry"], grupo.geometry.iloc[i]])
            destino["poblacion"] += grupo.poblacion.iloc[i]
            destino["poligonos_origen"].append(pid)
        else:
            nuevas_zonas.append({
                "geometry": grupo.geometry.iloc[i],
                "poblacion": grupo.poblacion.iloc[i],
                "poligonos_origen": [pid],
            })
        usados.add(i)
    
    return nuevas_zonas

# Aplicamos el proceso a cada sección censal
resultados = []

for seccion, grupo in zonas_core.groupby("seccion_codigo"):
    nuevas_zonas = agrupar_seccion(grupo)
    if len(nuevas_zonas) == len(grupo):
        print("No Hubo agrupaciones en la sección ", seccion)

    for zona in nuevas_zonas:
        resultados.append({
            "poligono_id": None,
            "tipo_zona": "Core",
            "depto_codigo": grupo["depto_codigo"].iloc[0],
            "depto_nombre": grupo["depto_nombre"].iloc[0],
            "seccion_codigo": seccion,
            "poblacion": zona["poblacion"],
            "poligonos_origen": zona["poligonos_origen"],
            "n_poligonos": len(zona["poligonos_origen"]),
            "geometry": zona["geometry"]
        })

# Creamos el GeoDataFrame con las zonas nuevas
zonificacion_agrupada = gpd.GeoDataFrame(resultados, crs=zonas_core.crs)

# Calculamos métricas para evaluar qué tan balanceadas quedaron
metricas = (zonificacion_agrupada.groupby("seccion_codigo")["poblacion"].agg(desviacion="std", poblacion_min = "min", poblacion_max = "max", poblacion_promedio = "mean", n_zonas="count").reset_index())
metricas["diferencia_max"] = (metricas["poblacion_max"] - metricas["poblacion_min"])

# Agregamos las métricas a cada zona
zonificacion_agrupada = zonificacion_agrupada.merge(metricas, on="seccion_codigo", how="left")

zonificacion_agrupada = (zonificacion_agrupada.sort_values(["seccion_codigo", "poblacion"]).reset_index(drop=True))
metricas.sort_values("desviacion", ascending=False)

No se encontró una solución con lb = 7 para la sección 0116
No Hubo agrupaciones en la sección  0125
No se encontró una solución con lb = 9 para la sección 0199
No Hubo agrupaciones en la sección  0303
No Hubo agrupaciones en la sección  0306
No se encontró una solución con lb = 7 para la sección 0317
No se encontró una solución con lb = 3 para la sección 0327
No Hubo agrupaciones en la sección  1600


,seccion_codigo,desviacion,poblacion_min,poblacion_max,poblacion_promedio,n_zonas,diferencia_max
32,0327,7837.695793,4335.789110,19960.173808,11783.232211,3,15624.384698
31,0317,5609.065198,337.620435,18344.555711,8486.128621,7,18006.935276
28,0305,5111.972752,6685.895183,13915.316379,10300.605781,2,7229.421196
10,0111,4028.624018,5086.140906,17365.481707,9202.451702,9,12279.340801
22,0123,3975.047437,5141.752579,12992.168582,8704.678799,3,7850.416003
20,0121,3961.731293,2302.946186,14586.615047,9027.069193,10,12283.668861
12,0113,3938.693685,3150.513480,19685.704195,6705.782229,14,16535.190715
29,0306,3763.686714,1511.825791,6834.482587,4173.154189,2,5322.656796
27,0304,3709.611753,3520.619241,14362.429087,8634.639397,11,10841.809846
15,0116,3550.966863,701.838207,10329.816574,5728.349821,8,9627.978367


A continuación, se listan los polígonos que quedaron solitarios. Estos corresponden a polígonos que son los únicos dentro de una sección censal o que únicamente tienen como vecinos zonas grandes, las cuales fueron excluidas del proceso de agrupación.

In [9]:
zonificacion_agrupada[(zonificacion_agrupada.n_poligonos==1)]

,poligono_id,tipo_zona,depto_codigo,depto_nombre,seccion_codigo,poblacion,poligonos_origen,n_poligonos,geometry,desviacion,poblacion_min,poblacion_max,poblacion_promedio,n_zonas,diferencia_max
96,None,Core,01,MONTEVIDEO,0116,701.838207,[555],1,"POLYGON ((557998.167 6141690.226, 557994.555 6...",3550.966863,701.838207,10329.816574,5728.349821,8,9627.978367
97,None,Core,01,MONTEVIDEO,0116,1922.890721,[495],1,"POLYGON ((558852.07 6149635.312, 558847.883 61...",3550.966863,701.838207,10329.816574,5728.349821,8,9627.978367
179,None,Core,01,MONTEVIDEO,0125,0.000000,[498],1,"POLYGON ((571704.789 6137058.079, 571702.051 6...",NaN,0.000000,0.000000,0.000000,1,0.000000
183,None,Core,01,MONTEVIDEO,0199,6631.265990,[566],1,"POLYGON ((585698.543 6150148.085, 585722.518 6...",2466.496229,3390.256259,11634.966322,7671.967713,9,8244.710063
189,None,Core,03,CANELONES,0303,3560.782822,[129],1,"POLYGON ((558001.776 6169525.871, 557989.799 6...",NaN,3560.782822,3560.782822,3560.782822,1,0.000000
203,None,Core,03,CANELONES,0306,1511.825791,[148],1,"POLYGON ((582635.978 6155244.675, 582632.052 6...",3763.686714,1511.825791,6834.482587,4173.154189,2,5322.656796
204,None,Core,03,CANELONES,0306,6834.482587,[83],1,"POLYGON ((585126.173 6164867.912, 585109.631 6...",3763.686714,1511.825791,6834.482587,4173.154189,2,5322.656796
206,None,Core,03,CANELONES,0317,337.620435,[151],1,"POLYGON ((601711.745 6159242.72, 601675.818 61...",5609.065198,337.620435,18344.555711,8486.128621,7,18006.935276
213,None,Core,03,CANELONES,0327,4335.789110,[150],1,"POLYGON ((601074.91 6159578.45, 601040.764 615...",7837.695793,4335.789110,19960.173808,11783.232211,3,15624.384698
234,None,Core,16,SAN JOSE,1600,0.000000,[141],1,"POLYGON ((546834.195 6166989.216, 546890.145 6...",NaN,0.000000,0.000000,0.000000,1,0.000000


A continuación, volvemos a calcular la columna CODSEG, con los segmentos censales que conforman cada nuevo polígono de la zonificacion.

In [10]:
# CODSEG: segmentos censales que conforman cada zona final

zonificacion_agrupada = zonificacion_agrupada.reset_index(drop=True)
zonificacion_agrupada["poligono_id"] = zonificacion_agrupada.index # asigno un ID único a cada zona final

segmentos_censales = gpd.read_file("../data/geography-levels/sg_23_pg.gpkg")
segmentos_codseg = segmentos_censales[["CODSEG", "geometry"]].copy()
segmentos_codseg["punto_rep"] = segmentos_codseg.geometry.representative_point()
segmentos_codseg = segmentos_codseg.set_geometry("punto_rep", crs=segmentos_censales.crs).to_crs(zonificacion_agrupada.crs)

segmentos_en_zona = gpd.sjoin(segmentos_codseg[["CODSEG", "punto_rep"]].set_geometry("punto_rep"), zonificacion_agrupada[["poligono_id", "geometry"]], how="left", predicate="within")

# Chequeo de duplicados
duplicados = segmentos_en_zona.dropna(subset=["poligono_id"]).groupby("CODSEG")["poligono_id"].nunique()
duplicados = duplicados[duplicados > 1]

if len(duplicados):
    print(f"Aviso: {len(duplicados)} CODSEG aparecen asignados a más de una zona final")

codseg_por_zona = (segmentos_en_zona.dropna(subset=["poligono_id"]).groupby("poligono_id")["CODSEG"].apply(lambda x: ", ".join(sorted(set(x.astype(str))))).reset_index()) # agrupo los CODSEG por zona
zonificacion_agrupada = zonificacion_agrupada.merge(codseg_por_zona, on="poligono_id", how="left") # agrego CODSEG a las zonas finales

zonificacion_agrupada["CODSEG"] = zonificacion_agrupada["CODSEG"].fillna("")

print(f"Zonas finales sin ningún CODSEG asignado: {(zonificacion_agrupada['CODSEG'] == '').sum()} de {len(zonificacion_agrupada)}")
print(f"Total de CODSEG distintos asignados a alguna zona: {segmentos_en_zona.dropna(subset=['poligono_id'])['CODSEG'].nunique()} de {segmentos_censales['CODSEG'].nunique()}")

Zonas finales sin ningún CODSEG asignado: 0 de 237
Total de CODSEG distintos asignados a alguna zona: 1256 de 4538


Incluimos nuevamente las zonas Periferia a la zonificación

In [11]:
zonas_no_agrupadas = zonificacion_a15_con_poblacion[~(zonificacion_a15_con_poblacion["poligono_id"].isin(zonas_core.poligono_id.tolist()))].copy()

zonificacion_final = pd.concat([zonificacion_agrupada, zonas_no_agrupadas], ignore_index=True)

zonificacion_final = gpd.GeoDataFrame(zonificacion_final, geometry="geometry", crs=zonificacion_a15_con_poblacion.crs)
zonificacion_final["poligono_id"] = range(len(zonificacion_final))

In [13]:
seg = segmentos_censales[["CODSEG", "geometry"]].to_crs(zonificacion_final.crs) # segmentos en el mismo CRS que la zonificación

# tabla (poligono_id, CODSEG): una fila por segmento de cada zona
asign = (zonificacion_final[["poligono_id", "CODSEG"]].assign(CODSEG=lambda d: d["CODSEG"].str.split(",")).explode("CODSEG"))
asign["CODSEG"] = asign["CODSEG"].str.strip()

# chequeo: un segmento no debería estar en más de una zona
dup = asign.groupby("CODSEG")["poligono_id"].nunique()
print(f"CODSEG asignados a más de una zona: {(dup > 1).sum()}")

# disolver los segmentos de cada zona
nuevas = (seg.merge(asign, on="CODSEG").dissolve(by="poligono_id").geometry)

# reemplazar la geometría por la reconstruida desde los segmentos
zonificacion_final["geometry"] = gpd.GeoSeries(zonificacion_final["poligono_id"].map(nuevas).values, index=zonificacion_final.index, crs=zonificacion_final.crs)

# chequeo
print("Zonas reconstruidas:", zonificacion_final["poligono_id"].isin(nuevas.index).sum(), "de", len(zonificacion_final))

CODSEG asignados a más de una zona: 0
Zonas reconstruidas: 329 de 329


In [14]:
zonas_nuevas = zonificacion_final[["seccion_codigo", "poblacion", "poligonos_origen", "desviacion", "diferencia_max", "geometry"]].copy()
zonas_nuevas["seccion_codigo"] = zonas_nuevas["seccion_codigo"].apply(str)

zonas_nuevas["poblacion"] = pd.to_numeric(zonas_nuevas["poblacion"], errors="coerce")
zonas_nuevas["desviacion"] = pd.to_numeric(zonas_nuevas["desviacion"], errors="coerce")
zonas_nuevas["diferencia_max"] = pd.to_numeric(zonas_nuevas["diferencia_max"], errors="coerce")

# Convertimos la lista de polígonos originales a texto
zonas_nuevas["poligonos_origen"] = zonas_nuevas["poligonos_origen"].apply(lambda x: ", ".join(str(i) for i in x)if isinstance(x, (list, tuple)) else "")
zonas_originales = zonificacion_a15_con_poblacion[zonificacion_a15_con_poblacion["tipo_zona"] == "Core"].copy()

zonas_originales["seccion_codigo"] = zonas_originales["seccion_codigo"].apply(str)
zonas_originales["poligono_id"] = zonas_originales["poligono_id"].apply(str)
zonas_originales["poblacion"] = pd.to_numeric(zonas_originales["poblacion"], errors="coerce")

secciones = secciones_censales[["CODSECC", "geometry"]].copy()
secciones["CODSECC"] = secciones["CODSECC"].apply(str)

# Pasamos todo a WGS84
zonas_nuevas = zonas_nuevas.to_crs("EPSG:4326")
zonas_originales = zonas_originales.to_crs("EPSG:4326")
secciones = secciones.to_crs("EPSG:4326")

# Centro del mapa
centro = zonas_nuevas.geometry.union_all().centroid

m = folium.Map(location=[centro.y, centro.x],zoom_start=9,tiles="OpenStreetMap")

# Secciones censales
folium.GeoJson(secciones, name="Secciones censales",
    style_function=lambda x: {
        "fillColor": "transparent",
        "color": "black",
        "weight": 1,
        "fillOpacity": 0
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["CODSECC"],
        aliases=["Sección"]
    )
).add_to(m)


# Zonas Core originales
folium.GeoJson(zonas_originales, name="Zonas Core originales", style_function=lambda x: {
        "fillColor": "blue",
        "color": "blue",
        "weight": 1,
        "fillOpacity": 0.25
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["poligono_id", "seccion_codigo", "poblacion"],
        aliases=["Polígono", "Sección", "Población"]
    )
).add_to(m)


# Zonas nuevas
folium.GeoJson(zonas_nuevas, name="Zonas nuevas", style_function=lambda x: {
        "fillColor": "orange"
        if x["properties"]["poblacion"] == 0
        else "red",
        "color": "orange"
        if x["properties"]["poblacion"] == 0
        else "red",
        "weight": 2,
        "fillOpacity": 0.35
    },
    tooltip=folium.GeoJsonTooltip(
        fields=[
            "seccion_codigo",
            "poblacion",
            "poligonos_origen",
            "desviacion",
            "diferencia_max"
        ],
        aliases=[
            "Sección",
            "Población",
            "Polígonos originales",
            "Desviación",
            "Diferencia máxima"
        ]
    )
).add_to(m)


folium.LayerControl(collapsed=False).add_to(m)

m

In [15]:
zonificacion_final["poblacion"] = pd.to_numeric(zonificacion_final["poblacion"], errors="coerce").round()
zonificacion_final.loc[zonificacion_final["poblacion"] == 0,"poblacion"] = np.nan # los que tienen población 0 es porque no encontró match. Por consistencia, lo cambio a nulo.
zonificacion_final = zonificacion_final[["poligono_id", "tipo_zona", "depto_codigo", "depto_nombre", "seccion_codigo", "CODSEG", "poblacion", "geometry"]]
zonificacion_final.to_file("../output/zonas-a15-agg.gpkg", driver="GPKG")